In [ ]:
from google.colab import auth
from google.cloud import bigquery
import pandas as pd

# 1. Authenticate with Google account
auth.authenticate_user()

# 2. Client configuration (Update to the latest project ID!)
project_id = 'youtube-analysis-v2-499813'
client = bigquery.Client(project=project_id)

# 3. Retrieve data directly from the latest standalone tables
query_dim = f"SELECT * FROM `{project_id}.youtube_data.dim_comments_umamusume` ORDER BY published_at DESC LIMIT 10000"
query_raw = f"SELECT * FROM `{project_id}.youtube_data.raw_comments_umamusume` ORDER BY published_at DESC LIMIT 10000"
query_fct = f"SELECT * FROM `{project_id}.youtube_data.fct_like_history_umamusume` LIMIT 10000"

print("📥 Fetching latest Umamusume data from BigQuery...")

# 4. Store in respective DataFrames
df_dim = client.query(query_dim).to_dataframe()
df_raw = client.query(query_raw).to_dataframe()
df_fct = client.query(query_fct).to_dataframe()

print("\n" + "━"*50)
print(f"✅ df_dim (Processed data)    Retrieved: {len(df_dim)} rows")
print(f"✅ df_raw (Raw data)          Retrieved: {len(df_raw)} rows")
print(f"✅ df_fct (Numeric history)   Retrieved: {len(df_fct)} rows")
print("━"*50)

# Check the structure of the processed data
display(df_dim.head())


📥 Fetching latest Umamusume data from BigQuery...

━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━
✅ df_dim (Processed data)    Retrieved: 10000 rows
✅ df_raw (Raw data)          Retrieved: 10000 rows
✅ df_fct (Numeric history)   Retrieved: 10000 rows
━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━


,comment_id,video_id,video_title,author_channel_id,brand,text_normalized,text_original,published_at,first_scraped_at
0,UgwLmp4wawVoVix2hk94AaABAg,4PCTrBadIB0,スティルが鏡に向かって… #shorts #ウマ娘,UCvp7K3XA5IiLsdScf51ZIkQ,UMAMUSUME,アルヴさん（トイレから出るの気まずいわ・・・）,アルヴさん（トイレから出るの気まずいわ・・・）,2026-10-16 16:23:42+00:00,2026-10-16 16:25:21.278589+00:00
1,UgwoZXjeskzfzQetM5Z4AaABAg,7nzJMGmS06g,【#プリコネR × #ウマ娘 コラボ記念】「Connecting Happy!!」 #踊って...,UCVC51z_HHUVG-PPD11enGjw,UMAMUSUME,この曲めっちゃ好きだったな懐かしい,この曲めっちゃ好きだったな懐かしい,2026-10-16 16:19:26+00:00,2026-10-16 16:25:21.278589+00:00
2,UgxLxUNydyemi7SmYCV4AaABAg,4PCTrBadIB0,スティルが鏡に向かって… #shorts #ウマ娘,UCNSC4sy4bw1HjLUlWzEPetg,UMAMUSUME,どっちのスティルも愛してるから一緒にビスコのファミリーパック食べようスティル！コーヒーもあるよ！,どっちのスティルも愛してるから一緒にビスコのファミリーパック食べようスティル！コーヒーもあるよ！,2026-10-16 16:14:41+00:00,2026-10-16 16:25:21.278589+00:00
3,Ugw3Tu__SRCJyaMcalJ4AaABAg,4PCTrBadIB0,スティルが鏡に向かって… #shorts #ウマ娘,UCIf4Ad9mqOAOTdfki8n_Jww,UMAMUSUME,トマトジュースにアイスキャンデーは\n合わないよ😹‼️,トマトジュースにアイスキャンデーは\n合わないよ😹‼️,2026-10-16 16:07:38+00:00,2026-10-16 16:25:21.278589+00:00
4,Ugw7WVazYOer-xvsSX54AaABAg,4PCTrBadIB0,スティルが鏡に向かって… #shorts #ウマ娘,UCP8vtmu0Sm_J4AEH0vQ65QA,UMAMUSUME,あの人は紅も含めてあなたを愛していますよ\nだから思うままにあの人の元へ…,あの人は紅も含めてあなたを愛していますよ\nだから思うままにあの人の元へ…,2026-10-16 16:00:01+00:00,2026-10-16 16:25:21.278589+00:00


In [ ]:
# ==================================================
# 💎 [Auto Drive Mount & Bug-Free] New Word Suggestion + GUI Dictionary Addition Cell
# ==================================================
import os
import sys
import collections
import pandas as pd
import subprocess
import json
from IPython import get_ipython
from IPython.display import display, clear_output

# 🌟🌟🌟 [Added] Automatically mount Google Drive if not connected 🌟🌟🌟
from google.colab import drive
if not os.path.exists('/content/drive/MyDrive'):
    print("🔗 Google Drive is not connected. Starting connection...")
    drive.mount('/content/drive')
else:
    print("✅ Google Drive is already connected.")

# 1. Automatic installation of required libraries
try:
    from sudachipy import dictionary, tokenizer
    import sudachidict_full
    import ipywidgets as widgets
except ModuleNotFoundError:
    print("📦 Required libraries are missing or removed.")
    print("⚙️ System is automatically restoring in the background (takes about 10-15 seconds)...")
    get_ipython().system(f'"{sys.executable}" -m pip install -q sudachipy sudachidict_full pandas ipywidgets')
    from sudachipy import dictionary, tokenizer
    import sudachidict_full
    import ipywidgets as widgets
    print("✅ Automatic system recovery completed! Starting analysis.")

# Folder path definition and automatic generation
drive_dir = "/content/drive/MyDrive/sudachi_dict1"
os.makedirs(drive_dir, exist_ok=True)

csv_path = os.path.join(drive_dir, "custom_dict.csv")
out_path = os.path.join(drive_dir, "user.dic")
config_path = "/content/sudachi_config.json"

# 2. Initialization of analysis engine (Loaded via JSON according to the latest API specs)
tokenizer_obj = None
if os.path.exists(out_path) and os.path.getsize(out_path) > 0:
    try:
        with open(config_path, "w", encoding="utf-8") as f:
            json.dump({"userDict": [out_path]}, f)
        tokenizer_obj = dictionary.Dictionary(dict="full", config_path=config_path).create()
        print("⚙️ Analysis engine: Initialized with full dictionary + user dictionary accumulated in Drive")
    except Exception as e:
        print(f"⚠️ Inconsistency found in previous user dictionary. Starting with standalone full dictionary for safety. ({e})")
        tokenizer_obj = dictionary.Dictionary(dict="full").create()
else:
    tokenizer_obj = dictionary.Dictionary(dict="full").create()
    print("⚙️ Analysis engine: Initialized as new (standalone full dictionary)")

mode = tokenizer.Tokenizer.SplitMode.C
compound_nouns = []
stop_surfaces = {'こと', 'もの', 'それ', 'これ', 'の', 'ため', 'よう', 'ところ', 'ん', 'そう', 'さん', 'ちゃん', 'くん', 'たち', 'やつ'}

# 3. Extract new words using data obtained from BigQuery (df_dim)
if 'df_dim' in locals() or 'df_dim' in globals():
    for text in df_dim['text_normalized'].dropna():
        tokens = tokenizer_obj.tokenize(text, mode)
        current_compound = []
        for m in tokens:
            pos = m.part_of_speech()[0]
            pos_detail = m.part_of_speech()[1]
            surface = m.surface()

            # Extract continuous nouns (exclude pronouns, numerals, non-independent nouns, etc.)
            if pos == "名詞" and pos_detail not in ["代名詞", "数詞", "非自立"] and surface not in stop_surfaces:
                current_compound.append(surface)
            else:
                if len(current_compound) >= 2:
                    compound_nouns.append("".join(current_compound))
                current_compound = []
        if len(current_compound) >= 2:
            compound_nouns.append("".join(current_compound))

    noun_counts = collections.Counter(compound_nouns)
    new_words_df = pd.DataFrame(noun_counts.most_common(15), columns=['New Word Candidate', 'Count in Data'])

    print("\n" + "━"*60)
    print("🚨 [Today's Top 15 New Word Suggestions] 🚨")
    print("(Previously registered words are automatically excluded and will not appear here)")
    print("━"*60)
    display(new_words_df)

    print("\n🎯 Select the words you want to register (hold Ctrl/Cmd for multiple selection) and click the green button:")
    options = [(f" [{idx}] {row['New Word Candidate']} (Count: {row['Count in Data']})", row['New Word Candidate']) for idx, row in new_words_df.iterrows()]

    # Create GUI components
    selector = widgets.SelectMultiple(options=options, value=[], disabled=False, layout=widgets.Layout(width='500px', height='250px', margin='10px 0px'))
    button = widgets.Button(description='Register Selected Words to Dictionary', disabled=False, button_style='success', icon='check', layout=widgets.Layout(width='400px', height='40px'))
    output_log = widgets.Output()

    # Event handler when button is clicked
    def on_button_clicked(b):
        with output_log:
            clear_output()
            selected_words = list(selector.value)
            if selected_words:
                print(f"➕ The following words were selected: {selected_words}")
                existing_lines = []
                if os.path.exists(csv_path):
                    with open(csv_path, "r", encoding="utf-8") as f:
                        existing_lines = f.readlines()

                for word_name in selected_words:
                    formatted_word = f"{word_name},4786,4786,-30000,{word_name},名詞,固有名詞,一般,*,*,*,*,{word_name},*,*,*,*,*\n"
                    if formatted_word not in existing_lines:
                        existing_lines.append(formatted_word)

                with open(csv_path, "w", encoding="utf-8") as f:
                    f.writelines(existing_lines)
                print(f"💾 Updated custom_dict.csv in Google Drive (Total registered: {len(existing_lines)})")

                dict_dir = sudachidict_full.__path__[0]
                system_dic = os.path.join(dict_dir, "resources", "system.dic")
                print("⚙️ Automatically building binary dictionary (user.dic)...")

                res = subprocess.run(["sudachipy", "ubuild", "-s", system_dic, csv_path, "-o", out_path], capture_output=True, text=True, encoding="utf-8")

                if res.returncode == 0:
                    print("\n✨ Success! The dictionary in Google Drive has been updated to the latest version!")
                else:
                    print(f"❌ An error occurred:\n{res.stderr}")
            else:
                print("ℹ️ No words selected. Click on the words in the box above to highlight them in blue.")

    button.on_click(on_button_clicked)
    display(selector, button, output_log)
else:
    print("❌ Error: `df_dim` not found. Please run 'Cell 0 (Data Retrieval)' at the top first.")

✅ Google Drive is already connected.
⚙️ Analysis engine: Initialized with full dictionary + user dictionary accumulated in Drive

━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━
🚨 [Today's Top 15 New Word Suggestions] 🚨
(Previously registered words are automatically excluded and will not appear here)
━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━


,New Word Candidate,Count in Data
0,ウインバリアシオン,26
1,シュヴァち,26
2,ノーザンホースパーク,21
3,さかな娘,20
4,ヴェルサイユリゾートファーム,18
5,スペシャルウィーク,17
6,トレセン学園,16
7,ジェンティルドンナ,16
8,ブラストワンピース,16
9,ゴールドシップ,15



🎯 Select the words you want to register (hold Ctrl/Cmd for multiple selection) and click the green button:


SelectMultiple(layout=Layout(height='250px', margin='10px 0px', width='500px'), options=((' [0] ウインバリアシオン (Cou…

Button(button_style='success', description='Register Selected Words to Dictionary', icon='check', layout=Layou…

Output()

In [ ]:
# ==================================================
# GUI cell for deleting and cleaning up registered words
# ==================================================
import os
import sys
import subprocess
import ipywidgets as widgets
from IPython.display import display, clear_output

# Define paths
drive_dir = "/content/drive/MyDrive/sudachi_dict1"
csv_path = os.path.join(drive_dir, "custom_dict.csv")
out_path = os.path.join(drive_dir, "user.dic")

output_del_log = widgets.Output()

def refresh_delete_ui():
    with output_del_log:
        clear_output()
        # If file does not exist or is empty
        if not os.path.exists(csv_path) or os.path.getsize(csv_path) == 0:
            print("ℹ️ No words are currently registered in the user dictionary.")
            return

        # Read CSV file
        with open(csv_path, "r", encoding="utf-8") as f:
            lines = f.readlines()

        registered_words = []
        for line in lines:
            if line.strip():
                word_name = line.split(",")[0]
                registered_words.append((word_name, line))

        if not registered_words:
            print("ℹ️ No valid registered words found.")
            return

        print(f"📚 Currently, {len(registered_words)} word(s) are registered.")
        print("🎯 Select the word(s) you want to delete from the dictionary (Hold Ctrl/Cmd to select multiple), then click the red button below:")

        # Create GUI components
        del_selector = widgets.SelectMultiple(options=registered_words, value=[], disabled=False, layout=widgets.Layout(width='500px', height='250px', margin='10px 0px'))
        del_button = widgets.Button(description='Delete selected words permanently', disabled=False, button_style='danger', icon='trash', layout=widgets.Layout(width='400px', height='40px'))

        # Process when delete button is clicked
        def on_del_button_clicked(b):
            with output_del_log:
                lines_to_delete = list(del_selector.value)
                if lines_to_delete:
                    # Reload the latest file
                    with open(csv_path, "r", encoding="utf-8") as f:
                        current_lines = f.readlines()

                    # Create new list excluding selected lines
                    new_lines = [line for line in current_lines if line not in lines_to_delete]

                    # Overwrite and save
                    with open(csv_path, "w", encoding="utf-8") as f:
                        f.writelines(new_lines)
                    print(f"\n🗑️ Selected words have been deleted.")

                    # Get SudachiDict_full path and rebuild
                    import sudachidict_full
                    dict_dir = sudachidict_full.__path__[0]
                    system_dic = os.path.join(dict_dir, "resources", "system.dic")
                    print("⚙️ Automatically rebuilding binary dictionary (user.dic)...")

                    res = subprocess.run(["sudachipy", "ubuild", "-s", system_dic, csv_path, "-o", out_path], capture_output=True, text=True, encoding="utf-8")

                    if res.returncode == 0:
                        print("✨ Successfully deleted and updated the dictionary!")
                        # Refresh UI to update status
                        refresh_delete_ui()
                    else:
                        print(f"❌ An error occurred:\n{res.stderr}")
                else:
                    print("⚠️ No words selected to delete. Please select from the box above.")

        del_button.on_click(on_del_button_clicked)
        display(del_selector, del_button)

# Initial UI render
refresh_delete_ui()
display(output_del_log)

Output()

In [ ]:
# ==========================================
# [Step 2/3 Final Version] c-TF-IDF Auto-Tagging & Full English UI (v2 table supported)
# ==========================================

# ==========================================
# Preparation: Install required libraries
# ==========================================
!pip install -q fugashi unidic-lite sentence-transformers umap-learn hdbscan openpyxl scikit-learn

# @title ⚙️ Ultimate Custom Analysis Panel (1-click full auto processing)
# @markdown ---
GCP_PROJECT_ID = 'youtube-analysis-v2-499813' # @param {type:"string"}
DATASET_ID = 'youtube_data' # @param {type:"string"}

# @markdown ### 🏢 0. Select Target Brand
TARGET_BRAND = 'umamusume' # @param ["umamusume", "jal"]

# @markdown ### 📅 1. Specify Period (Based on comment post date)
PERIOD_MODE = "Recent months (All data)" # @param ["Recent months (All data)", "Specify any period"]
START_DATE = "2026-05-10" # @param {type:"string"}
END_DATE = "2026-05-17" # @param {type:"string"}

# @markdown ### 🔥 2. Condition A: Island Formation (Core Data) Extraction Rules
COND_A_LIKES = 10 # @param {type:"integer"}
COND_A_REPLIES = 0 # @param {type:"integer"}
COND_A_GTE_LTE = "Greater/Equal" # @param ["Greater/Equal", "Less/Equal"]
COND_A_KW1 = "" # @param {type:"string"}
COND_A_KW2 = "" # @param {type:"string"}
COND_A_KW3 = "" # @param {type:"string"}

# @markdown ### 💬 3. Condition B: Allocation (Target Data) Extraction Rules
COND_B_LIKES = 9 # @param {type:"integer"}
COND_B_REPLIES = 0 # @param {type:"integer"}
COND_B_GTE_LTE = "Less/Equal" # @param ["Greater/Equal", "Less/Equal"]
COND_B_KW1 = "" # @param {type:"string"}
COND_B_KW2 = "" # @param {type:"string"}
COND_B_KW3 = "" # @param {type:"string"}

# @markdown ### 🔀 4. Island Allocation Logic Selection
ALLOCATION_MODE = "2. Overflow + All B comments" # @param ["1. Overflowed comments only", "2. Overflow + All B comments"]

# @markdown ### 🎛️ 5. Topic Classification Tuning (Adjust with slider)
TOPIC_SCOPE = 15 # @param {type:"slider", min:5, max:50, step:1}
MIN_CLUSTER_SIZE = 15 # @param {type:"slider", min:5, max:100, step:1}
CLUSTER_PURITY_FILTER = 0.5 # @param {type:"slider", min:0.0, max:1.0, step:0.1}
# @markdown ---

import pandas as pd
import numpy as np
from google.cloud import bigquery
from google.colab import auth
from google.colab import data_table
from sentence_transformers import SentenceTransformer
import umap
import hdbscan
import fugashi
from sklearn.feature_extraction.text import TfidfVectorizer, CountVectorizer
from sklearn.metrics.pairwise import cosine_similarity
from sklearn.metrics import silhouette_score
import warnings
import ipywidgets as widgets
from IPython.display import display

# Disable warnings
warnings.filterwarnings('ignore')

# --- [STEP 1] Google Cloud Authentication & BigQuery Data Extraction ---
print("🔑 Authenticating Google Cloud...")
auth.authenticate_user()
bq_client = bigquery.Client(project=GCP_PROJECT_ID)

sql_op_a = ">=" if COND_A_GTE_LTE == "Greater/Equal" else "<="
sql_op_b = ">=" if COND_B_GTE_LTE == "Greater/Equal" else "<="

def build_keyword_clause(keywords):
    valid_kws = [kw.strip() for kw in keywords if kw.strip()]
    if not valid_kws:
        return ""
    clauses = [f"c.text_normalized LIKE '%{kw}%'" for kw in valid_kws]
    return f"AND ({' OR '.join(clauses)})"

kw_a = build_keyword_clause([COND_A_KW1, COND_A_KW2, COND_A_KW3])
kw_b = build_keyword_clause([COND_B_KW1, COND_B_KW2, COND_B_KW3])

if PERIOD_MODE == "Recent months (All data)":
    date_clause = "c.published_at >= TIMESTAMP_SUB(CURRENT_TIMESTAMP(), INTERVAL 90 DAY)"
else:
    date_clause = f"c.published_at BETWEEN TIMESTAMP('{START_DATE} 00:00:00') AND TIMESTAMP('{END_DATE} 23:59:59')"

# Dynamically generate table names for the selected brand
table_dim = f"`{GCP_PROJECT_ID}.{DATASET_ID}.dim_comments_{TARGET_BRAND}`"
table_fct = f"`{GCP_PROJECT_ID}.{DATASET_ID}.fct_like_history_{TARGET_BRAND}`"

query = f"""
    SELECT
      c.comment_id,
      c.text_normalized,
      c.video_title,
      h.like_count,
      h.reply_count,
      c.published_at,
      CASE
        WHEN (h.like_count {sql_op_a} {COND_A_LIKES} AND h.reply_count >= {COND_A_REPLIES} {kw_a}) THEN 'A'
        WHEN (h.like_count {sql_op_b} {COND_B_LIKES} AND h.reply_count >= {COND_B_REPLIES} {kw_b}) THEN 'B'
        ELSE 'NONE'
      END as target_group
    FROM
      {table_dim} c
    JOIN
      {table_fct} h
      ON c.comment_id = h.comment_id
    WHERE
      c.text_normalized IS NOT NULL
      AND {date_clause}
    QUALIFY ROW_NUMBER() OVER(PARTITION BY c.comment_id ORDER BY h.checked_at DESC) = 1
    ORDER BY
      c.published_at DESC;
"""

print(f"📥 Extracting data for ({TARGET_BRAND}) from BigQuery...")
df_raw = bq_client.query(query).to_dataframe()

df_a = df_raw[df_raw['target_group'] == 'A'].copy().reset_index(drop=True)
df_b = df_raw[df_raw['target_group'] == 'B'].copy().reset_index(drop=True)

if len(df_a) == 0:
    raise ValueError("⚠️ Condition A returned 0 records. Please relax the conditions.")

# --- [STEP 2] SimCSE High-Precision Vectorization ---
df_for_embed = pd.concat([df_a, df_b], ignore_index=True)
print("🧠 Vectorizing with SimCSE model (T4 GPU execution)...")
model = SentenceTransformer("pkshatech/simcse-ja-bert-base-clcmlp")
embeddings = model.encode(df_for_embed['text_normalized'].tolist(), show_progress_bar=False)

df_for_embed['embedding'] = list(embeddings)
df_a_vect = df_for_embed[df_for_embed['target_group'] == 'A'].copy().reset_index(drop=True)
df_b_vect = df_for_embed[df_for_embed['target_group'] == 'B'].copy().reset_index(drop=True)

# --- [STEP 3] Latest Priority Sampling & Data Splitting ---
SAMPLE_LIMIT = min(15000, len(df_a_vect))
df_core = df_a_vect.iloc[:SAMPLE_LIMIT].copy().reset_index(drop=True)
df_overflow = df_a_vect.iloc[SAMPLE_LIMIT:].copy().reset_index(drop=True)

if "1." in ALLOCATION_MODE:
    df_remain = df_overflow
else:
    df_remain = pd.concat([df_overflow, df_b_vect], ignore_index=True)

n_core = len(df_core)
n_remain = len(df_remain)
core_embeddings = np.array(df_core['embedding'].tolist())
remain_embeddings = np.array(df_remain['embedding'].tolist()) if n_remain > 0 else np.empty((0, 768))

# --- [STEP 4 & 5] UMAP & HDBSCAN Clustering ---
print("🗺️ Learning spatial representation and allocating topics (islands)...")

reducer = umap.UMAP(
    n_neighbors=TOPIC_SCOPE,
    n_components=5,
    metric='cosine',
    random_state=42,
    low_memory=True
)
reduced_core = reducer.fit_transform(core_embeddings)
reduced_remain = reducer.transform(remain_embeddings) if n_remain > 0 else np.empty((0, 5))

clusterer = hdbscan.HDBSCAN(
    min_cluster_size=MIN_CLUSTER_SIZE,
    metric='euclidean',
    cluster_selection_method='eom',
    prediction_data=True
)
core_labels = clusterer.fit_predict(reduced_core)
core_probs = clusterer.probabilities_

core_labels_strict = [label if prob >= CLUSTER_PURITY_FILTER else -1 for label, prob in zip(core_labels, core_probs)]
df_core['cluster_label'] = core_labels_strict
df_core['membership_prob'] = core_probs

if n_remain > 0:
    remain_labels, strengths = hdbscan.approximate_predict(clusterer, reduced_remain)
    remain_labels_strict = [label if prob >= CLUSTER_PURITY_FILTER else -1 for label, prob in zip(remain_labels, strengths)]
    df_remain['cluster_label'] = remain_labels_strict
    df_remain['membership_prob'] = strengths
else:
    df_remain['cluster_label'] = np.array([])
    df_remain['membership_prob'] = np.array([])

df_result = pd.concat([df_core, df_remain], ignore_index=True)
valid_df = df_result[df_result['cluster_label'] != -1].copy()
unique_clusters = sorted(valid_df['cluster_label'].unique())

# --- [STEP 6] Auto-Tagging Islands via c-TF-IDF ---
print("🏷️ Extracting symbolic keywords for each island using c-TF-IDF...")
tagger = fugashi.Tagger()
# Note: Stop words and POS tags remain in Japanese to properly process the Japanese comments.
stop_words = {'こと', 'もの', 'の', 'よう', 'これ', 'それ', 'あれ', 'どれ', 'さん', 'ちゃん', 'くん', 'ため', 'ところ', 'はず', 'わけ', 'そう', 'みたい'}

def tokenize_for_keywords(text):
    words = []
    for word in tagger(text):
        if word.feature.pos1 in ['名詞', '形容詞']:
            lemma = word.feature.lemma if word.feature.lemma else word.surface
            if lemma not in stop_words and len(lemma) > 1:
                words.append(lemma)
    return " ".join(words)

cluster_tags_dict = {}
if len(unique_clusters) > 0:
    cluster_docs = []
    for c_id in unique_clusters:
        raw_texts = valid_df[valid_df['cluster_label'] == c_id]['text_normalized'].tolist()
        tokenized_doc = " ".join([tokenize_for_keywords(t) for t in raw_texts])
        cluster_docs.append(tokenized_doc)

    if len(unique_clusters) == 1:
        vectorizer = CountVectorizer()
    else:
        vectorizer = TfidfVectorizer()

    tf_matrix = vectorizer.fit_transform(cluster_docs)
    feature_names = vectorizer.get_feature_names_out()

    for i, c_id in enumerate(unique_clusters):
        row = tf_matrix.getrow(i).toarray()[0]
        top_indices = row.argsort()[-4:][::-1]
        tags = [f"[{feature_names[idx]}]" for idx in top_indices if row[idx] > 0]
        cluster_tags_dict[c_id] = "".join(tags)

df_result['Auto_Extracted_Tags'] = df_result['cluster_label'].map(cluster_tags_dict).fillna('[Noise]')
valid_df = df_result[df_result['cluster_label'] != -1].copy()

# --- [STEP 7] Aggregate Summary Display ---
total_comments = len(df_result)
noise_comments = len(df_result[df_result['cluster_label'] == -1])
island_comments = total_comments - noise_comments
n_clusters = len(unique_clusters)

print("\n" + "="*70)
print(f"📈 [Data Aggregation Summary ({TARGET_BRAND})]")
print(f"  ▶ Total comments processed : {total_comments}")
print(f"  ▶ Number of islands formed : {n_clusters}")
print(f"  ▶ Valid classified records : {island_comments}")
print(f"  ▶ Excluded as noise        : {noise_comments} (Label -1)")
print("="*70 + "\n")

# --- [STEP 8] Quantitative Evaluation & Keyword Extraction Report ---
if len(unique_clusters) >= 2:
    X_valid = np.stack(valid_df['embedding'].values)
    labels_valid = valid_df['cluster_label'].values
    sil_score = silhouette_score(X_valid, labels_valid, metric='cosine')
    print(f"🌍 Overall Silhouette Score: {sil_score:.3f} (Guide: >0.0 is valid, >0.5 is extremely clear)")

print("\n🏝️ Island Details (Auto-Tags & Representative Comments):")
for cluster_id in unique_clusters:
    vectors = np.stack(valid_df[valid_df['cluster_label'] == cluster_id]['embedding'].values)
    if len(vectors) > 1:
        sim_matrix = cosine_similarity(vectors)
        np.fill_diagonal(sim_matrix, np.nan)
        avg_sim = np.nanmean(sim_matrix)
        tags = cluster_tags_dict.get(cluster_id, "No Tags")

        print(f"\n  ▶ Island {cluster_id:2d} {tags} (Members: {len(vectors):4d}) -> "
              f"Avg Similarity: {avg_sim:.3f}")
        print("      [Top 3 Representative Comments]")

        top_comments = valid_df[valid_df['cluster_label'] == cluster_id].sort_values(by='membership_prob', ascending=False).head(3)
        for rank, row in enumerate(top_comments.itertuples(), 1):
            prob_percent = row.membership_prob * 100

            # Replaces line breaks with spaces for single-line output
            clean_text = str(row.text_normalized).replace('\n', ' ').replace('\r', '')

            print(f"       Rank {rank} (Purity {prob_percent:5.1f}%): {clean_text}")

# --- [STEP 9] Table Formatting and Display ---
display_df_en = df_result[['cluster_label', 'Auto_Extracted_Tags', 'membership_prob', 'like_count', 'reply_count', 'text_normalized']].copy()
display_df_en = display_df_en.rename(columns={
    'cluster_label': 'Cluster_ID',
    'Auto_Extracted_Tags': 'Extracted_Tags',
    'membership_prob': 'Purity_Prob',
    'like_count': 'Likes',
    'reply_count': 'Replies',
    'text_normalized': 'Comment_Text'
})
display_df_en = display_df_en.sort_values(['Cluster_ID', 'Purity_Prob'], ascending=[True, False]).reset_index(drop=True)

print("\n👀 [Full Results Preview]")
data_table.enable_dataframe_formatter()
display(display_df_en)

# --- [STEP 10] Excel Download Button ---
print("\n")
button = widgets.Button(description=f"📥 Download Results as Excel ({TARGET_BRAND})", button_style='success', layout=widgets.Layout(width='auto'))
output = widgets.Output()

def on_button_clicked(b):
    with output:
        from google.colab import files
        filename = f'{TARGET_BRAND}_clustering_result.xlsx'
        display_df_en.to_excel(filename, index=False)
        files.download(filename)
        print(f"✅ Download started for {filename}!")

button.on_click(on_button_clicked)
display(button, output)

🔑 Authenticating Google Cloud...
📥 Extracting data for (umamusume) from BigQuery...
🧠 Vectorizing with SimCSE model (T4 GPU execution)...


Loading weights:   0%|          | 0/199 [00:00<?, ?it/s]

🗺️ Learning spatial representation and allocating topics (islands)...
🏷️ Extracting symbolic keywords for each island using c-TF-IDF...

📈 [Data Aggregation Summary (umamusume)]
  ▶ Total comments processed : 19555
  ▶ Number of islands formed : 6
  ▶ Valid classified records : 15960
  ▶ Excluded as noise        : 3595 (Label -1)

🌍 Overall Silhouette Score: 0.011 (Guide: >0.0 is valid, >0.5 is extremely clear)

🏝️ Island Details (Auto-Tags & Representative Comments):

  ▶ Island  0 [旨い][ベルサイユ][薔薇][競馬] (Members: 1558) -> Avg Similarity: 0.390
      [Top 3 Representative Comments]
       Rank 1 (Purity 100.0%): ウマ娘の日常…！ありがたや… 今回は大富豪か。豪華なメンバーだし 実装の決まったルーラーシップも居るのね。素敵だ…
       Rank 2 (Purity 100.0%): 推しのトウカイテイオーに癒される
       Rank 3 (Purity 100.0%): ウマ娘大富豪、実装してほしいんだが

  ▶ Island  1 [ダンス][dance][振り付け][可愛い] (Members:   96) -> Avg Similarity: 0.531
      [Top 3 Representative Comments]
       Rank 1 (Purity 100.0%): プリコネから見たらウマ娘組の方が明らかに全員ダンス上手いのが細かい モーションキャプチャーする人達って凄い、ガチでダンスできる人のモーションとダンスの素人の

,Cluster_ID,Extracted_Tags,Purity_Prob,Likes,Replies,Comment_Text
0,-1,[Noise],0.499939,0,0,"we need more animation like that, cy games is ..."
1,-1,[Noise],0.499910,0,0,so we're family approved?
2,-1,[Noise],0.499846,8,0,my favorite dog
3,-1,[Noise],0.499749,0,0,not once during the whole 3 minutes could i co...
4,-1,[Noise],0.499747,1,0,chevacci va meets real chevacci
...,...,...,...,...,...,...
19550,5,[可愛い][良い][無い][スペ],0.759734,2,0,インポスターの時ちょいちょい犬化するのおもろいｗｗ
19551,5,[可愛い][良い][無い][スペ],0.759710,0,0,グッドのポーズがdena佐野恵太のアウトポーズにしか見えない奇病……
19552,5,[可愛い][良い][無い][スペ],0.759603,1,0,エル「エルエルは、クルーでした～」\nスカイ「嘘つけ！」（食い気味）
19553,5,[可愛い][良い][無い][スペ],0.759570,6,0,騎士道精神のオーラは消え失せ、代わりに十代の少女のかわいらしさが漂っている。


Button(button_style='success', description='📥 Download Results as Excel (umamusume)', layout=Layout(width='aut…

Output()

In [ ]:
# ==================================================
# 🎯 [Step 4] FAISS + BM25 5-Level Comparison Dashboard (⚡Ultra-Fast + ML Auto-Sort✨)
# ==================================================
import os
import sys
import numpy as np
import pandas as pd
import json
import warnings
import unicodedata  # For full-width/half-width normalization
from IPython import get_ipython
from sklearn.neighbors import KNeighborsRegressor

warnings.filterwarnings('ignore')

# --------------------------------------------------
# 🌟 0. Google Drive Auto-Mount Check
# --------------------------------------------------
drive_path = '/content/drive/MyDrive'
if not os.path.exists(drive_path):
    print("🔗 Google Drive is not connected. Starting auto-mount...")
    from google.colab import drive
    drive.mount('/content/drive')
else:
    print("🔗 Google Drive is already connected.")

print("📦 Setting up search engine, morphological analysis, and ML libraries...")
get_ipython().system(f'"{sys.executable}" -m pip install -q faiss-cpu rank-bm25 sudachipy sudachidict_full scikit-learn')

import faiss
from rank_bm25 import BM25Okapi
import ipywidgets as widgets
from IPython.display import display, clear_output, HTML
from sudachipy import dictionary, tokenizer

# --------------------------------------------------
# 1. Robust Data Inheritance
# --------------------------------------------------
target_df = globals().get('df_result')
target_model = globals().get('model', globals().get('simcse_model'))

if target_df is None or target_model is None or 'embedding' not in target_df.columns:
    print("\n❌ Error: Required data not found. Please run the 'Step 2/3' cell first.")
else:
    target_embeddings = np.stack(target_df['embedding'].values)

    # --------------------------------------------------
    # 2. Keyword & Semantic Search Setup
    # --------------------------------------------------
    drive_dir = "/content/drive/MyDrive/sudachi_dict1"
    out_path = os.path.join(drive_dir, "user.dic")
    config_path = "/content/sudachi_config.json"
    os.makedirs(drive_dir, exist_ok=True)

    if os.path.exists(out_path) and os.path.getsize(out_path) > 0:
        with open(config_path, "w", encoding="utf-8") as f:
            json.dump({"userDict": [out_path]}, f)
        sudachi_engine = dictionary.Dictionary(dict="full", config_path=config_path).create()
    else:
        sudachi_engine = dictionary.Dictionary(dict="full").create()

    split_mode = tokenizer.Tokenizer.SplitMode.C

    def tokenize_for_search(text):
        if not isinstance(text, str): return []
        # Keep Japanese POS tags as Sudachi internally outputs these exact Japanese strings
        return [m.surface() for m in sudachi_engine.tokenize(text, split_mode) if m.part_of_speech()[0] in ["名詞", "動詞", "形容詞"]]

    docs = target_df['text_normalized'].tolist()
    tokenized_corpus = [tokenize_for_search(doc) for doc in docs]
    bm25 = BM25Okapi(tokenized_corpus)

    faiss_index_path = "/content/drive/MyDrive/faiss_index.bin"
    dimension = target_embeddings.shape[1]

    if os.path.exists(faiss_index_path):
        print("📂 Loading existing FAISS index...")
        faiss_index = faiss.read_index(faiss_index_path)
    else:
        print("💾 Creating and saving a new FAISS index...")
        faiss_index = faiss.IndexFlatIP(dimension)
        embeddings_float32 = np.array(target_embeddings, dtype=np.float32)
        faiss.normalize_L2(embeddings_float32)
        faiss_index.add(embeddings_float32)
        faiss.write_index(faiss_index, faiss_index_path)

    # --------------------------------------------------
    # 3. [Speed-up] Preload and Cache ML Prediction Model
    # --------------------------------------------------
    EVAL_FILE = "/content/drive/MyDrive/faiss_bm25_evaluations.csv"
    global_knn = None
    global_X = []
    global_y = []

    # Variables to hold the current search query state for evaluation
    current_query = ""
    current_query_embedding = None

    if os.path.exists(EVAL_FILE):
        print("🤖 Loading past evaluation data for AI training...")
        df_eval = pd.read_csv(EVAL_FILE).tail(300) # Limit to latest 300 records for speed
        if not df_eval.empty:
            past_queries = df_eval['query'].tolist()
            global_X = target_model.encode(past_queries).tolist()
            global_y = df_eval[['score_0.0', 'score_0.25', 'score_0.5', 'score_0.75', 'score_1.0']].values.tolist()

            global_knn = KNeighborsRegressor(n_neighbors=min(3, len(global_X)), weights='distance')
            global_knn.fit(global_X, global_y)

    clear_output()

    # --------------------------------------------------
    # 4. [Speed-up] Hybrid Search (RRF reusing pre-calculated scores)
    # --------------------------------------------------
    def hybrid_search_fast(weight_semantic, bm25_scores, bm25_ranking, semantic_ranking, top_k=10):
        weight_keyword = 1.0 - weight_semantic
        k_const = 60
        rrf_scores = {str(i): 0.0 for i in range(len(docs))}

        for rank, doc_id in enumerate(bm25_ranking):
            if bm25_scores[doc_id] > 0:
                rrf_scores[str(doc_id)] += weight_keyword * (1.0 / (k_const + rank + 1))

        for rank, doc_id in enumerate(semantic_ranking):
            if doc_id != -1 and doc_id < len(docs):
                rrf_scores[str(doc_id)] += weight_semantic * (1.0 / (k_const + rank + 1))

        sorted_docs = sorted(rrf_scores.items(), key=lambda x: x[1], reverse=True)

        results = []
        for doc_id_str, score in sorted_docs[:top_k]:
            if score > 0:
                idx = int(doc_id_str)
                row = target_df.iloc[idx]
                results.append({
                    "RRF_Score": round(score, 4),
                    "Cluster_ID": row.get('cluster_label', '-'),
                    # Supports both English & original Japanese keys for seamless transition
                    "Extracted_Tags": row.get('Auto_Extracted_Tags', row.get('自動抽出タグ', '-')),
                    "Likes": row.get('like_count', 0),
                    "Replies": row.get('reply_count', 0),
                    "Comment_Text": row.get('text_normalized', '')
                })
        return pd.DataFrame(results)

    # --------------------------------------------------
    # 5. UI Components Construction
    # --------------------------------------------------
    html_header = widgets.HTML("""
    <div style="background-color: #2F4F4F; padding: 15px; border-radius: 8px; color: white; margin-bottom: 10px;">
        <h3 style="margin: 0; font-size: 18px;">🔍 FAISS + BM25 5-Level Comparison Dashboard (⚡Ultra-Fast + AI Auto-Sort)</h3>
        <p style="margin: 5px 0 0 0; font-size: 13px;">💡 Predicts optimal search ratios from past evaluation data and automatically sorts them from highest score.</p>
    </div>
    """)

    input_query = widgets.Text(
        value='', placeholder='e.g., The live performance energy was the best', description='🔍 Query:',
        style={'description_width': 'initial'}, layout=widgets.Layout(width='80%', height='40px')
    )

    btn_search = widgets.Button(
        description='✨ 5-Pattern Search', button_style='info', icon='search',
        layout=widgets.Layout(width='200px', height='45px', margin='10px 0')
    )

    output_search = widgets.Output()

    # Evaluation Input UI
    rating_widgets = {}
    for w in [0.0, 0.25, 0.5, 0.75, 1.0]:
        rating_widgets[w] = widgets.Text(
            value='0', placeholder='Number 0~3', description=f'Weight {w}:',
            style={'description_width': 'initial'}, layout=widgets.Layout(width='140px')
        )

    save_eval_btn = widgets.Button(
        description='💾 Save Eval & Train AI', button_style='success', icon='save',
        layout=widgets.Layout(width='220px', height='40px', margin='10px 10px 10px 0')
    )

    reset_eval_btn = widgets.Button(
        description='🗑️ Reset All AI Training Data', button_style='danger', icon='trash',
        layout=widgets.Layout(width='250px', height='40px', margin='10px 0')
    )

    eval_output = widgets.Output()

    # --------------------------------------------------
    # 6. Action Definitions
    # --------------------------------------------------
    def on_search_clicked(b):
        global current_query, current_query_embedding
        with output_search:
            clear_output(wait=True)
            query = input_query.value.strip()
            if not query:
                print("⚠️ Please enter a search query.")
                return

            print(f"🔎 Searching for '{query}'... (Fast computing 5 patterns in bulk)\n")

            current_query = query
            tokenized_query = tokenize_for_search(query)
            bm25_scores = bm25.get_scores(tokenized_query)
            bm25_ranking = np.argsort(bm25_scores)[::-1][:100]

            current_query_embedding = target_model.encode([query])
            query_embedding_float32 = np.array(current_query_embedding, dtype=np.float32)
            faiss.normalize_L2(query_embedding_float32)
            D, I = faiss_index.search(query_embedding_float32, 100)
            semantic_ranking = I[0]

            pred_scores = {0.0: 0.0, 0.25: 0.0, 0.5: 0.0, 0.75: 0.0, 1.0: 0.0}
            if global_knn is not None:
                try:
                    pred = global_knn.predict(current_query_embedding)[0]
                    pred_scores = {0.0: pred[0], 0.25: pred[1], 0.5: pred[2], 0.75: pred[3], 1.0: pred[4]}
                except:
                    pass

            scenarios = [
                {"weight": 0.0,  "title": '🔑 0.0 (Dict-Focus)',     "desc": "<b>[0.0: Dictionary-Focused]</b> Keyword search (BM25). Requires exact word match to hit."},
                {"weight": 0.25, "title": '🔎 0.25 (Keyword-Lean)', "desc": "<b>[0.25: Keyword-Leaning]</b> Dictionary-based matching supplemented with slight AI context."},
                {"weight": 0.5,  "title": '⚖️ 0.5 (Balanced)',      "desc": "<b>[0.5: Balanced Type]</b> Best of both worlds. True Hybrid Search (RRF)."},
                {"weight": 0.75, "title": '🧠 0.75 (Context-Lean)', "desc": "<b>[0.75: AI Context-Leaning]</b> Focuses heavily on AI semantic understanding while slightly considering search keywords."},
                {"weight": 1.0,  "title": '✨ 1.0 (AI-Focus)',       "desc": "<b>[1.0: AI Semantic-Focused]</b> Context-reading AI semantic search (FAISS). Hits similar meanings even if words differ."}
            ]

            for scene in scenarios:
                scene['pred'] = pred_scores[scene['weight']]

            sorted_scenarios = sorted(scenarios, key=lambda x: x['pred'], reverse=True)

            tab_children = []
            col_explanation = """
            <div style="background-color: #e9ecef; padding: 12px; border-radius: 5px; margin-bottom: 12px; font-size: 13px; color: #333;">
                <b>📊 [How to Read]</b> (💡 Click table headers to toggle ascending/descending order)<br>
                <span style="color:#d9534f">●</span> <b>RRF_Score:</b> Overall match score with search conditions (higher = better fit)<br>
                <span style="color:#f0ad4e">●</span> <b>Cluster_ID / Extracted_Tags:</b> Topic grouping and its summary label<br>
                <span style="color:#e83e8c">●</span> <b>Likes / Replies:</b> Breadth of empathy and intensity of discussion for the comment
            </div>
            """

            for scene in sorted_scenarios:
                df_res = hybrid_search_fast(scene["weight"], bm25_scores, bm25_ranking, semantic_ranking, top_k=10)
                html_table = df_res.to_html(index=False, escape=False)

                div_id = f"table_wrapper_{int(scene['weight']*100)}"

                html_content = f"""
                <div style="margin-bottom: 10px; padding: 10px; background-color: #f8f9fa; border-left: 4px solid #483D8B;">
                    <span style="font-size: 14px; color: #333;">{scene['desc']}</span><br>
                    <span style="font-size: 12px; color: #888;">🤖 AI Expected Satisfaction Score: <b>{scene['pred']:.2f} Points</b></span>
                </div>
                {col_explanation}

                <style>
                #{div_id} .dataframe {{border-collapse: collapse; width: 100%; font-size: 13px; table-layout: fixed;}}
                #{div_id} .dataframe th {{background-color: #f2f2f2; padding: 10px; text-align: center; border: 1px solid #c0c0c0; font-weight: bold; cursor: pointer; transition: background 0.2s; user-select: none;}}
                #{div_id} .dataframe th:hover {{background-color: #dcdcdc;}}
                #{div_id} .dataframe th::after {{content: ' ⇅'; font-size: 12px; color: #888; margin-left: 4px;}}
                #{div_id} .dataframe td {{padding: 10px; border: 1px solid #e0e0e0; text-align: left; word-wrap: break-word; overflow-wrap: break-word;}}
                #{div_id} .dataframe tr:nth-child(even) {{background-color: #fafafa;}}
                #{div_id} .dataframe th:nth-child(1) {{width: 10%;}}
                #{div_id} .dataframe td:nth-child(1) {{text-align: center; font-weight: bold; color: #2F4F4F;}}
                #{div_id} .dataframe th:nth-child(2) {{width: 8%;}}
                #{div_id} .dataframe td:nth-child(2) {{text-align: center;}}
                #{div_id} .dataframe th:nth-child(3) {{width: 15%;}}
                #{div_id} .dataframe th:nth-child(4) {{width: 8%;}}
                #{div_id} .dataframe td:nth-child(4) {{text-align: center; color: #e83e8c; font-weight: bold;}}
                #{div_id} .dataframe th:nth-child(5) {{width: 8%;}}
                #{div_id} .dataframe td:nth-child(5) {{text-align: center; color: #007bff; font-weight: bold;}}
                #{div_id} .dataframe th:nth-child(6) {{width: 51%;}}
                </style>

                <div id="{div_id}">
                    {html_table}
                </div>

                <script>
                (function() {{
                    if (typeof window.bindTableSort !== 'function') {{
                        window.bindTableSort = function(containerId) {{
                            var container = document.getElementById(containerId);
                            if (!container) return;
                            if (container.getAttribute('data-sort-bound')) return;

                            container.addEventListener('click', function(e) {{
                                var th = e.target.closest('th');
                                if (!th) return;

                                var table = th.closest('table');
                                var tbody = table.querySelector('tbody');
                                if (!tbody) return;

                                var rows = Array.from(tbody.querySelectorAll('tr'));
                                var index = Array.from(th.parentNode.children).indexOf(th);
                                var currentOrder = th.getAttribute('data-order') || 'desc';
                                var newOrder = currentOrder === 'desc' ? 'asc' : 'desc';

                                var headers = table.querySelectorAll('th');
                                headers.forEach(h => h.setAttribute('data-order', ''));
                                th.setAttribute('data-order', newOrder);

                                rows.sort(function(a, b) {{
                                    var aText = a.children[index].innerText.trim();
                                    var bText = b.children[index].innerText.trim();
                                    var aVal = parseFloat(aText.replace(/,/g, ''));
                                    var bVal = parseFloat(bText.replace(/,/g, ''));

                                    if (!isNaN(aVal) && !isNaN(bVal)) {{
                                        return newOrder === 'asc' ? aVal - bVal : bVal - aVal;
                                    }} else {{
                                        return newOrder === 'asc' ? aText.localeCompare(bText) : bText.localeCompare(aText);
                                    }}
                                }});

                                tbody.innerHTML = '';
                                rows.forEach(row => tbody.appendChild(row));
                            }});

                            container.setAttribute('data-sort-bound', 'true');
                            var headers = container.querySelectorAll('th');
                            headers.forEach(h => {{
                                h.style.cursor = 'pointer';
                                h.title = 'Click to toggle ascending/descending';
                            }});
                        }};
                    }}

                    var checkExist_{div_id} = setInterval(function() {{
                        if (document.getElementById('{div_id}')) {{
                            window.bindTableSort('{div_id}');
                            clearInterval(checkExist_{div_id});
                        }}
                    }}, 200);
                }})();
                </script>
                """

                out_tab = widgets.Output()
                with out_tab:
                    display(HTML(html_content))
                tab_children.append(out_tab)

            tab = widgets.Tab(children=tab_children)
            for i, scene in enumerate(sorted_scenarios):
                tab.set_title(i, f"{scene['title']} (Pred⭐{scene['pred']:.1f})")

            display(tab)

    # --------------------------------------------------
    # 7. Evaluation & Reset Handlers
    # --------------------------------------------------
    def on_save_eval(b):
        global global_knn, global_X, global_y, current_query, current_query_embedding
        with eval_output:
            clear_output()
            if not current_query or current_query_embedding is None:
                print("⚠️ Please run a search before saving evaluations.")
                return

            scores = {}
            for w in rating_widgets:
                val_str = rating_widgets[w].value.strip()
                val_str = unicodedata.normalize('NFKC', val_str)
                try:
                    val = int(val_str)
                    if val < 0: val = 0
                    if val > 3: val = 3
                except ValueError:
                    print(f"⚠️ [Warning] Invalid input for weight {w}. Auto-setting to '0'.")
                    val = 0
                scores[w] = val
                rating_widgets[w].value = str(val)

            new_data = pd.DataFrame([{
                'query': current_query,
                'score_0.0': scores[0.0], 'score_0.25': scores[0.25], 'score_0.5': scores[0.5],
                'score_0.75': scores[0.75], 'score_1.0': scores[1.0]
            }])

            # Allow unlimited overwrites
            if os.path.exists(EVAL_FILE):
                df_eval = pd.read_csv(EVAL_FILE)
                df_eval = df_eval[df_eval['query'] != current_query]
                df_eval = pd.concat([df_eval, new_data], ignore_index=True)
                df_eval.to_csv(EVAL_FILE, index=False)
            else:
                new_data.to_csv(EVAL_FILE, index=False)

            # Dynamic KNN Model Update
            query_emb_list = current_query_embedding[0].tolist()
            if query_emb_list in global_X:
                idx = global_X.index(query_emb_list)
                global_y[idx] = [scores[0.0], scores[0.25], scores[0.5], scores[0.75], scores[1.0]]
            else:
                global_X.append(query_emb_list)
                global_y.append([scores[0.0], scores[0.25], scores[0.5], scores[0.75], scores[1.0]])

            if global_knn is None:
                global_knn = KNeighborsRegressor(n_neighbors=min(3, len(global_X)), weights='distance')
            else:
                global_knn.n_neighbors = min(3, len(global_X))

            global_knn.fit(global_X, global_y)

            print(f"✅ Saved evaluation ({current_query}) and updated prediction model! (Took few ms)")
            print("💡 You can overwrite the learning data for the same query anytime.")

    def on_reset_eval(b):
        global global_knn, global_X, global_y
        with eval_output:
            clear_output()
            if os.path.exists(EVAL_FILE):
                os.remove(EVAL_FILE)
            global_knn = None
            global_X = []
            global_y = []
            print("🗑️ All AI training data (past evaluation CSV) has been reset!")
            print("💡 AI prediction scores will return to initial state from the next search.")

    btn_search.on_click(on_search_clicked)
    save_eval_btn.on_click(on_save_eval)
    reset_eval_btn.on_click(on_reset_eval)

    # --------------------------------------------------
    # 8. UI Display Generation
    # --------------------------------------------------
    ui_search = widgets.VBox([html_header, input_query, btn_search])

    eval_ui = widgets.VBox([
        widgets.HTML("<hr><h4 style='color: #d9534f;'>⭐ Evaluate the search results of each pattern (Enter a half-width number from 0 to 3)</h4>"),
        widgets.HBox(list(rating_widgets.values()), layout=widgets.Layout(margin='10px 0')),
        widgets.HBox([save_eval_btn, reset_eval_btn]),
        eval_output
    ], layout=widgets.Layout(padding='10px', border='2px dashed #d9534f', margin='20px 0', background_color='#fff5f5'))

    display(ui_search, output_search, eval_ui)

Output()

In [ ]:
# ==================================================
# 🚀 [Final Step] Master Data Export for Tableau Integration
# (Auto X/Y Coordinate Generation & Full Date Restoration & Reply Count Support)
# ==================================================
import os
import pandas as pd
import numpy as np
from datetime import datetime
from IPython import get_ipython
from IPython.display import display, clear_output, HTML

print("📦 Preparing final master data...")
# Install library for coordinate calculation just in case
get_ipython().system('pip install -q umap-learn')

# --------------------------------------------------
# 1. Automatic Data Detection (Retrieve results directly from Step 2/3)
# --------------------------------------------------
target_df = globals().get('df_result')

if target_df is None:
    print("❌ Error: No export data found. Please run the 'Step 2/3' cell first.")
else:
    # --------------------------------------------------
    # 2. [Date] Robust Data Restoration
    # --------------------------------------------------
    print("🔍 Searching for date information from raw historical data...")
    mapping_dict = {}

    for var_name, var_val in list(globals().items()):
        if isinstance(var_val, pd.DataFrame) and 'text_normalized' in var_val.columns and 'published_at' in var_val.columns:
            temp_dict = var_val.drop_duplicates('text_normalized').set_index('text_normalized')['published_at'].to_dict()
            mapping_dict.update(temp_dict)

    if mapping_dict:
        target_df['Date'] = target_df['text_normalized'].map(mapping_dict)
        target_df['Date'] = pd.to_datetime(target_df['Date'], errors='coerce').dt.tz_localize(None)
        print("✅ Date data successfully restored!")
    else:
        target_df['Date'] = pd.NaT
        print("⚠️ Date data could not be found.")

    # --------------------------------------------------
    # 3. [X/Y Coordinates] Auto-calculation & Generation
    # --------------------------------------------------
    print("🌌 Calculating spatial coordinates (x, y) for Tableau from AI embeddings...")
    # Check if embedding exists in target_df
    if 'embedding' in target_df.columns:
        import umap
        # Compress high-dimensional vectors to 2D (x, y) for Tableau using UMAP
        reducer = umap.UMAP(n_neighbors=15, n_components=2, metric='cosine', random_state=42)
        embeddings_array = np.stack(target_df['embedding'].values)
        coords = reducer.fit_transform(embeddings_array)
        target_df['x'] = coords[:, 0]
        target_df['y'] = coords[:, 1]
        print("✅ Coordinates (x, y) generated successfully!")
    else:
        print("⚠️ AI data (embeddings) required for coordinate calculation not found.")

    # --------------------------------------------------
    # 4. Column Alignment and Output
    # --------------------------------------------------
    # Map column names to English (supports both original Japanese and previous English key names)
    rename_dict = {
        'cluster_label': 'Cluster_ID',
        'like_count': 'Likes',
        'reply_count': 'Replies',
        'text_normalized': 'Comment_Text',
        '自動抽出タグ': 'Extracted_Tags',
        'Auto_Extracted_Tags': 'Extracted_Tags',
        '島番号': 'Cluster_ID',
        'いいね数': 'Likes',
        '返信数': 'Replies',
        'コメント本文': 'Comment_Text',
        '日付': 'Date'
    }
    export_df = target_df.rename(columns=rename_dict).copy()

    final_cols = ['Date', 'x', 'y', 'Cluster_ID', 'Extracted_Tags', 'Likes', 'Replies', 'Comment_Text']
    existing_cols = [col for col in final_cols if col in export_df.columns]
    final_export_df = export_df[existing_cols]

    # Save to Google Drive
    drive_dir = '/content/drive/MyDrive'
    if not os.path.exists(drive_dir):
        from google.colab import drive
        drive.mount('/content/drive')

    # Retrieve target brand name (supports both English and Japanese variable names)
    brand_name = globals().get('TARGET_BRAND', globals().get('分析対象ブランド', 'fandom'))
    timestamp = datetime.now().strftime("%Y%m%d_%H%M")
    file_name = f"{brand_name}_master_data_{timestamp}.xlsx"
    file_path = os.path.join(drive_dir, file_name)

    print(f"💾 Saving data to Google Drive in Excel format... ({len(final_export_df)} records)")
    final_export_df.to_excel(file_path, index=False, engine='openpyxl')

    extracted_cols_str = ', '.join(existing_cols)

    html_msg = f"""
    <div style="background-color: #e8f5e9; padding: 20px; border-radius: 8px; border-left: 5px solid #4caf50;">
        <h3 style="margin-top: 0; color: #2e7d32;">🎉 Master Data Export Successful!</h3>
        <p><b>Save Path:</b> <code>{file_path}</code></p>
        <p>A complete file optimized for Tableau analysis has been generated with the following combined data:</p>
        <ul>
            <li>📅 <b>Date</b> (For time-series analysis)</li>
            <li>🌌 <b>x, y</b> (UMAP coordinates for Tableau scatter plots)</li>
            <li>🏷️ <b>Cluster_ID / Extracted_Tags</b></li>
            <li>❤️ <b>Likes / 💬 Replies / Comment_Text</b></li>
        </ul>
        <p style="color: #555; font-size: 0.9em;">※ Extracted columns in this run: <b>{extracted_cols_str}</b></p>
        <hr style="border-top: 1px solid #c8e6c9;">
        <p><b>📌 Next Steps:</b> Download this file from Google Drive and reload it in Tableau's "Data Source" screen!</p>
    </div>
    """

    clear_output()
    display(HTML(html_msg))

    # --------------------------------------------------
    # Trigger automatic 1-time local download
    # --------------------------------------------------
    from google.colab import files
    print(f"📥 Starting local download for {file_name}...")

    try:
        files.download(file_path)
    except Exception as e:
        print(f"⚠️ Error occurred during download: {e}")
        print("Please download manually from the folder icon 📁 on the left panel.")

📥 Starting local download for umamusume_master_data_20261017_0523.xlsx...


<IPython.core.display.Javascript object>

<IPython.core.display.Javascript object>

In [ ]:
# ==================================================
# 🧪 Corporate Philosophy Comparative Analysis System (Data Retention & Prompt Appending & Selective Deletion)
# ==================================================
!pip install -q -U google-generativeai sentence-transformers ipywidgets beautifulsoup4 scipy

import google.generativeai as genai
import ipywidgets as widgets
from IPython.display import display, HTML, clear_output
from bs4 import BeautifulSoup
import numpy as np
from sentence_transformers import SentenceTransformer
from scipy.spatial.distance import cosine
import json
import time
import re

# --- 0. Common Definitions and State Persistence ---
definitions = {
    "Mission": "What to provide to society/customers, reason for existence",
    "Value": "Strengths and specific focus in products/services",
    "Mind": "Behavioral guidelines and attitudes practiced by employees/teams"
}

INITIAL_DEFAULT_PROMPT = "Extract only the most important 【single sentence】 corresponding to '{category}' from the input text.\nDefinition: {definition}\nMultiple sentences are not allowed. You must extract exactly one sentence as it is from the original text (summarizing or fabricating is strictly prohibited). The output must be strictly in JSON format (dictionary object) only and not enclosed in a list [ ]."

# Check global space in Colab and initialize if they do not exist (persists across cell re-runs)
if 'saved_prompts' not in globals():
    saved_prompts = {}
if 'html_cache' not in globals():
    html_cache = {}
if 'base_data_a' not in globals():
    base_data_a = {}
if 'base_data_b' not in globals():
    base_data_b = {}

print("🧠 Loading SimCSE model... (This will take a few dozen seconds)")
simcse_model = SentenceTransformer("pkshatech/simcse-ja-bert-base-clcmlp")
clear_output()

# --- 1. Create UI Components ---
mode_selector = widgets.RadioButtons(
    options=[
        '1️⃣ [Classic Method] Upload HTML file and let AI extract automatically',
        '2️⃣ [Bypass API Limits] Input manually extracted text directly into the form'
    ],
    value='1️⃣ [Classic Method] Upload HTML file and let AI extract automatically',
    layout=widgets.Layout(width='100%', margin='0 0 20px 0')
)

api_key_input = widgets.Password(description='🔑 API Key:', placeholder='Enter key starting with AI...', layout=widgets.Layout(width='50%'))

def create_upload_slot(company, category):
    label_html = widgets.HTML(f"<div style='margin-bottom:3px;'><b>{category}</b> <span style='font-size:12px; color:#555;'>({definitions[category]})</span></div>")
    uploader = widgets.FileUpload(accept='.html', multiple=False, description='Select File', layout=widgets.Layout(width='70%'))
    clear_btn = widgets.Button(description='🗑️ Clear', button_style='danger', layout=widgets.Layout(width='28%'))

    def on_clear_clicked(b):
        if isinstance(uploader.value, dict): uploader.value.clear()
        else: uploader.value = ()
        uploader._counter = 0
        wid = id(uploader)
        if wid in html_cache: del html_cache[wid]

    clear_btn.on_click(on_clear_clicked)
    ui_box = widgets.HBox([uploader, clear_btn], layout=widgets.Layout(width='100%', justify_content='space-between'))
    return widgets.VBox([label_html, ui_box], layout=widgets.Layout(margin='0 0 10px 0')), uploader

m1_slots_a = {"Mission": create_upload_slot('A', 'Mission'), "Value": create_upload_slot('A', 'Value'), "Mind": create_upload_slot('A', 'Mind')}
m1_slots_b = {"Mission": create_upload_slot('B', 'Mission'), "Value": create_upload_slot('B', 'Value'), "Mind": create_upload_slot('B', 'Mind')}

def create_textarea(company, category):
    label_html = widgets.HTML(f"<div style='margin-bottom:3px;'><b>{category}</b> <span style='font-size:12px; color:#555;'>({definitions[category]})</span></div>")
    textarea = widgets.Textarea(placeholder='Paste text here', layout=widgets.Layout(width='100%', height='80px'))
    return widgets.VBox([label_html, textarea], layout=widgets.Layout(margin='0 0 10px 0')), textarea

m2_slots_a = {"Mission": create_textarea('A', 'Mission'), "Value": create_textarea('A', 'Value'), "Mind": create_textarea('A', 'Mind')}
m2_slots_b = {"Mission": create_textarea('B', 'Mission'), "Value": create_textarea('B', 'Value'), "Mind": create_textarea('B', 'Mind')}

ui_container = widgets.VBox()

# 🌟 Prompt Selection / Deletion UI
prompt_selector = widgets.RadioButtons(options=['Use the initial default prompt'], value='Use the initial default prompt', layout=widgets.Layout(width='100%'))
decision_container_delete = widgets.VBox()

prompt_box = widgets.VBox([
    widgets.HTML("<h4 style='margin:0 0 10px 0;'>📝 Select Extraction Prompt to Use</h4>"),
    prompt_selector,
    widgets.HTML("<hr style='margin:15px 0;'><h4 style='margin:0 0 10px 0;'>🗑️ Manage Saved Prompts (Select to Delete)</h4>"),
    decision_container_delete
], layout=widgets.Layout(margin='15px 0', padding='15px', border='1px solid #ddd', background_color='#fdfdfd'))

def update_prompt_ui():
    opts = ['Use the initial default prompt'] + list(saved_prompts.keys())
    current_val = prompt_selector.value
    prompt_selector.options = opts
    if current_val in opts:
        prompt_selector.value = current_val
    else:
        prompt_selector.value = 'Use the initial default prompt'

    if not saved_prompts:
        decision_container_delete.children = [widgets.HTML("<span style='color:#999; font-size:13px;'>No additional saved prompts currently available.</span>")]
    else:
        cbs = [widgets.Checkbox(description=k, layout=widgets.Layout(width='auto'), style={'description_width': 'initial'}) for k in saved_prompts.keys()]
        del_btn = widgets.Button(description='🗑️ Delete Checked Items', button_style='danger', layout=widgets.Layout(margin='10px 0 0 0'))

        def on_delete(b):
            for cb in cbs:
                if cb.value and cb.description in saved_prompts:
                    del saved_prompts[cb.description]
            update_prompt_ui()

        del_btn.on_click(on_delete)
        decision_container_delete.children = cbs + [del_btn]

# Reflect saved data upon UI initialization
update_prompt_ui()

run_btn = widgets.Button(description='🚀 Run Comparative Analysis', button_style='primary', layout=widgets.Layout(width='100%', margin='5px 0 0 0', height='45px'))
initial_result_area = widgets.Output()
rerun_loading_area = widgets.Output()
rerun_result_area = widgets.Output()
feedback_container = widgets.VBox()
decision_container = widgets.VBox()

feedback_input = widgets.Textarea(placeholder='e.g., Please pick up more abstract expressions and include a bit of inference', layout=widgets.Layout(width='100%', height='60px'))
rerun_btn = widgets.Button(description='🔄 Apply Additional Instructions and Re-run', button_style='warning', layout=widgets.Layout(width='100%', height='40px'))
feedback_box = widgets.VBox([
    widgets.HTML("<h4>🛠 Dissatisfied with the extraction results? Write your requests, and the prompt will be updated. (*Requests will be appended to the initial prompt*)</h4>"),
    feedback_input,
    rerun_btn
], layout=widgets.Layout(margin='20px 0 0 0', padding='15px', border='1px solid #ddd', background_color='#fdfdfd'))


# --- 2. Mode Switching Logic ---
def update_ui(*args):
    if '1️⃣' in mode_selector.value:
        col_a = widgets.VBox([widgets.HTML("<h3 style='color:#007bff;'>🏢 Company A (HTML)</h3>"), m1_slots_a["Mission"][0], m1_slots_a["Value"][0], m1_slots_a["Mind"][0]], layout=widgets.Layout(width='48%'))
        col_b = widgets.VBox([widgets.HTML("<h3 style='color:#dc3545;'>🏢 Company B (HTML)</h3>"), m1_slots_b["Mission"][0], m1_slots_b["Value"][0], m1_slots_b["Mind"][0]], layout=widgets.Layout(width='48%'))
        panel = widgets.HBox([col_a, col_b], layout=widgets.Layout(justify_content='space-between'))
        ui_container.children = [widgets.HTML("<hr><h4>⚙️ AI Auto-Extraction Settings</h4>"), api_key_input, panel]
    else:
        col_a = widgets.VBox([widgets.HTML("<h3 style='color:#007bff;'>🏢 Company A (Direct Input)</h3>"), m2_slots_a["Mission"][0], m2_slots_a["Value"][0], m2_slots_a["Mind"][0]], layout=widgets.Layout(width='48%'))
        col_b = widgets.VBox([widgets.HTML("<h3 style='color:#dc3545;'>🏢 Company B (Direct Input)</h3>"), m2_slots_b["Mission"][0], m2_slots_b["Value"][0], m2_slots_b["Mind"][0]], layout=widgets.Layout(width='48%'))
        panel = widgets.HBox([col_a, col_b], layout=widgets.Layout(justify_content='space-between'))
        ui_container.children = [widgets.HTML("<hr><h4>✍️ Manual Text Input (No API Communication / High Speed)</h4>"), panel]

mode_selector.observe(update_ui, 'value')
update_ui()

# --- 3. Extraction & Calculation Logic ---
def get_safe_vector(text):
    return np.array(simcse_model.encode(str(text))).flatten()

def extract_from_html(uploader_widget, category, api_key, custom_prompt=None):
    if not uploader_widget.value: return "Not Uploaded"
    try:
        wid = id(uploader_widget)
        if wid in html_cache:
            text = html_cache[wid]
        else:
            val = uploader_widget.value
            content = val[list(val.keys())[0]]['content'] if isinstance(val, dict) else val[0]['content']
            html_text = bytes(content).decode('utf-8', errors='ignore')
            soup = BeautifulSoup(html_text, 'html.parser')
            for s in soup(["script", "style", "nav", "footer"]): s.decompose()
            text = soup.get_text(separator=' ', strip=True)[:10000]
            html_cache[wid] = text

        genai.configure(api_key=api_key)
        model = genai.GenerativeModel('gemini-3.1-flash-lite')

        template = custom_prompt if custom_prompt else INITIAL_DEFAULT_PROMPT
        prompt = template.replace("{category}", category).replace("{definition}", definitions[category])

        for attempt in range(3):
            try:
                response = model.generate_content(prompt + f"\n\nInput Text:\n{text}", generation_config={"temperature": 0, "response_mime_type": "application/json"})
                raw_text = response.text.strip()
                match = re.search(r'```json\s*(.*?)\s*```', raw_text, re.DOTALL)
                if match: raw_text = match.group(1)

                res_json = json.loads(raw_text)
                res_dict = res_json[0] if isinstance(res_json, list) else res_json
                result = str(res_dict.get(category, "No match found"))

                result = result.replace('\n', ' ').strip()
                if '。' in result: result = result.split('。')[0] + '。'
                if len(result) > 100: result = result[:97] + "..."
                return result
            except Exception as e:
                if "429" in str(e) or "Quota" in str(e): time.sleep(15)
                else: return f"Extraction Error: {e}"
        return "API Limit Error"
    except Exception as e:
        return f"Error: {e}"

def make_bar_with_text(label, score, a_text, b_text, definition):
    if score is None:
        return f"""
        <div style="margin-bottom: 20px;">
            <div style="display: flex; justify-content: space-between; font-size: 14px; font-weight: bold; color: #333; margin-bottom: 6px;">
                <span>{label} <span style="font-weight:normal; color:#777; font-size:12px;">({definition})</span></span>
                <span style="color: #9e9e9e;">Not measured</span>
            </div>
            <div style="background-color: #e0e0e0; border-radius: 4px; height: 8px; width: 100%; overflow: hidden; margin-bottom: 8px;">
                <div style="background-color: #9e9e9e; width: 0%; height: 100%;"></div>
            </div>
            <div style="background-color: #fcfcfc; border-left: 3px solid #ccc; padding: 6px 10px; font-size: 11.5px; color: #666; line-height: 1.5; border-radius: 0 4px 4px 0;">
                <div style="margin-bottom: 2px;"><span style="color: #007bff; font-weight: bold;">🏢 Company A:</span> {a_text}</div>
                <div><span style="color: #dc3545; font-weight: bold;">🏢 Company B:</span> {b_text}</div>
            </div>
        </div>"""

    color = "#4caf50" if score >= 70 else "#ff9800" if score >= 50 else "#f44336"
    return f"""
    <div style="margin-bottom: 20px;">
        <div style="display: flex; justify-content: space-between; font-size: 14px; font-weight: bold; color: #333; margin-bottom: 6px;">
            <span>{label} <span style="font-weight:normal; color:#777; font-size:12px;">({definition})</span></span>
            <span style="color: {color};">{score:.1f}%</span>
        </div>
        <div style="background-color: #e0e0e0; border-radius: 4px; height: 8px; width: 100%; overflow: hidden; margin-bottom: 8px;">
            <div style="background-color: {color}; width: {score}%; height: 100%;"></div>
        </div>
        <div style="background-color: #fcfcfc; border-left: 3px solid #ccc; padding: 6px 10px; font-size: 11.5px; color: #666; line-height: 1.5; border-radius: 0 4px 4px 0;">
            <div style="margin-bottom: 2px;"><span style="color: #007bff; font-weight: bold;">🏢 Company A:</span> {a_text}</div>
            <div><span style="color: #dc3545; font-weight: bold;">🏢 Company B:</span> {b_text}</div>
        </div>
    </div>"""

def on_run_click(b):
    global base_data_a, base_data_b
    feedback_container.children = []
    decision_container.children = []
    rerun_loading_area.clear_output()
    rerun_result_area.clear_output()

    with initial_result_area:
        clear_output()
        is_ai_mode = '1️⃣' in mode_selector.value
        data_a, data_b = {}, {}
        categories = ["Mission", "Value", "Mind"]

        # 🌟 Get selected prompt
        active_label = prompt_selector.value
        active_prompt = INITIAL_DEFAULT_PROMPT if active_label == 'Use the initial default prompt' else saved_prompts.get(active_label, INITIAL_DEFAULT_PROMPT)

        if is_ai_mode:
            if not api_key_input.value:
                print("❌ Error: Please enter your API key.")
                return
            print("🔍 Starting analysis in AI extraction mode...")
            for cat in categories:
                print(f"▶ Analyzing {cat} for 【Company A】...")
                data_a[cat] = extract_from_html(m1_slots_a[cat][1], cat, api_key_input.value, custom_prompt=active_prompt)
                time.sleep(15)
                print(f"▶ Analyzing {cat} for 【Company B】...")
                data_b[cat] = extract_from_html(m1_slots_b[cat][1], cat, api_key_input.value, custom_prompt=active_prompt)
                time.sleep(2)
        else:
            print("⚡ Running high-speed analysis in manual input mode...")
            for cat in categories:
                data_a[cat] = m2_slots_a[cat][1].value if m2_slots_a[cat][1].value else "Not entered"
                data_b[cat] = m2_slots_b[cat][1].value if m2_slots_b[cat][1].value else "Not entered"

        base_data_a = data_a.copy()
        base_data_b = data_b.copy()

        clear_output()

        scores = {}
        for cat in categories:
            val_a, val_b = data_a[cat], data_b[cat]
            if ("No match found" in val_a or "No match found" in val_b or
                "Error" in val_a or "Error" in val_b or
                "Not Uploaded" in val_a or "Not Uploaded" in val_b or
                val_a == "Not entered" or val_b == "Not entered" or
                not val_a.strip() or not val_b.strip()):
                scores[cat] = None
            else:
                scores[cat] = (1 - cosine(get_safe_vector(val_a), get_safe_vector(val_b))) * 100

        valid_scores = [s for s in scores.values() if s is not None]

        if valid_scores:
            avg_score = np.mean(valid_scores)
            avg_color = "#4caf50" if avg_score >= 70 else "#ff9800" if avg_score >= 50 else "#f44336"
            evaluation = "Extremely High Resonance" if avg_score >= 75 else "High Affinity" if avg_score >= 60 else "Moderate Affinity" if avg_score >= 40 else "Different Approaches (Needs Alignment)"
            score_html = f"{avg_score:.1f}%"
        else:
            avg_color = "#9e9e9e"
            evaluation = "Cannot be determined (No valid data)"
            score_html = "Not measured"

        html_msg = f"""
        <div style="background-color: #f8f9fa; padding: 25px; border-radius: 12px; border: 2px solid #e0e0e0; font-family: sans-serif;">
            <h3 style="margin-top: 0; color: #333; text-align: center;">📊 Corporate Philosophy Vector Comprehensive Matching Judgment</h3>
            <div style="display: flex; justify-content: space-between; margin-top: 25px; gap: 20px;">
                <div style="width: 35%; text-align: center; background-color: #fff; padding: 20px; border-radius: 8px; border: 1px solid #ddd; display: flex; flex-direction: column; justify-content: center;">
                    <h4 style="margin: 0 0 10px 0; color: #333;">💡 Comprehensive Base Score (Ideal)</h4>
                    <div style="font-size: 54px; font-weight: bold; color: {avg_color}; line-height: 1.0;">{score_html}</div>
                    <div style="font-size: 16px; font-weight: bold; color: #555; margin-top: 15px;">Judgment: {evaluation}</div>
                </div>
                <div style="width: 65%; background-color: #fff; padding: 20px 25px 5px 25px; border-radius: 8px; border: 1px solid #ddd;">
                    {make_bar_with_text("1. Mission", scores["Mission"], data_a["Mission"], data_b["Mission"], definitions["Mission"])}
                    {make_bar_with_text("2. Value", scores["Value"], data_a["Value"], data_b["Value"], definitions["Value"])}
                    {make_bar_with_text("3. Mind", scores["Mind"], data_a["Mind"], data_b["Mind"], definitions["Mind"])}
                </div>
            </div>
        </div>"""
        display(HTML(html_msg))

    if is_ai_mode:
        feedback_container.children = [feedback_box]

# --- 4. Prompt Appending (Additional Instruction) Logic ---
def on_rerun_click(b):
    global base_data_a, base_data_b

    rerun_result_area.clear_output()
    rerun_loading_area.clear_output()
    decision_container.children = []

    with rerun_loading_area:
        if not feedback_input.value:
            display(HTML("<div style='color:red; padding:10px;'>❌ Error: Please enter additional instructions/requests.</div>"))
            return
        display(HTML("<div style='margin:20px 0; padding:20px; text-align:center; background-color:#fff3cd; color:#856404; border:1px solid #ffeeba; border-radius:8px; font-size:16px; font-weight:bold;'>⏳ Applying additional instructions and re-analyzing. Please wait...</div>"))

    genai.configure(api_key=api_key_input.value)

    # 🌟 Skip AI generation and append user feedback directly as a string to the initial prompt
    user_feedback_text = feedback_input.value.strip()
    appended_prompt_template = INITIAL_DEFAULT_PROMPT + f"\n\n[Additional Instructions]\n{user_feedback_text}"

    data_a, data_b = {}, {}
    categories = ["Mission", "Value", "Mind"]

    for cat in categories:
        res_a = extract_from_html(m1_slots_a[cat][1], cat, api_key_input.value, custom_prompt=appended_prompt_template)
        if "No match found" in res_a or "Error" in res_a or res_a.strip() == "": res_a = base_data_a.get(cat, "No match found (Failed in initial run as well)")
        data_a[cat] = res_a
        time.sleep(2)

        res_b = extract_from_html(m1_slots_b[cat][1], cat, api_key_input.value, custom_prompt=appended_prompt_template)
        if "No match found" in res_b or "Error" in res_b or res_b.strip() == "": res_b = base_data_b.get(cat, "No match found (Failed in initial run as well)")
        data_b[cat] = res_b
        time.sleep(2)

    scores = {}
    for cat in categories:
        val_a, val_b = data_a[cat], data_b[cat]
        if ("No match found" in val_a or "No match found" in val_b or
            "Error" in val_a or "Error" in val_b or
            "Not Uploaded" in val_a or "Not Uploaded" in val_b or
            val_a == "Not entered" or val_b == "Not entered" or
            not val_a.strip() or not val_b.strip()):
            scores[cat] = None
        else:
            scores[cat] = (1 - cosine(get_safe_vector(val_a), get_safe_vector(val_b))) * 100

    valid_scores = [s for s in scores.values() if s is not None]

    if valid_scores:
        avg_score = np.mean(valid_scores)
        avg_color = "#4caf50" if avg_score >= 70 else "#ff9800" if avg_score >= 50 else "#f44336"
        evaluation = "Extremely High Resonance" if avg_score >= 75 else "High Affinity" if avg_score >= 60 else "Moderate Affinity" if avg_score >= 40 else "Different Approaches (Needs Alignment)"
        score_html = f"{avg_score:.1f}%"
    else:
        avg_color = "#9e9e9e"
        evaluation = "Cannot be determined (No valid data)"
        score_html = "Not measured"

    html_msg = f"""
    <div style="background-color: #e3f2fd; padding: 25px; border-radius: 12px; border: 2px solid #b8daff; font-family: sans-serif; margin-top:20px;">
        <h3 style="margin-top: 0; color: #0056b3; text-align: center;">🚀 Re-matching Judgment with Additional Instructions</h3>
        <div style="display: flex; justify-content: space-between; margin-top: 25px; gap: 20px;">
            <div style="width: 35%; text-align: center; background-color: #fff; padding: 20px; border-radius: 8px; border: 1px solid #ddd; display: flex; flex-direction: column; justify-content: center;">
                <h4 style="margin: 0 0 10px 0; color: #333;">💡 Comprehensive Base Score (Ideal)</h4>
                <div style="font-size: 54px; font-weight: bold; color: {avg_color}; line-height: 1.0;">{score_html}</div>
                <div style="font-size: 16px; font-weight: bold; color: #555; margin-top: 15px;">Judgment: {evaluation}</div>
            </div>
            <div style="width: 65%; background-color: #fff; padding: 20px 25px 5px 25px; border-radius: 8px; border: 1px solid #ddd;">
                {make_bar_with_text("1. Mission", scores["Mission"], data_a["Mission"], data_b["Mission"], definitions["Mission"])}
                {make_bar_with_text("2. Value", scores["Value"], data_a["Value"], data_b["Value"], definitions["Value"])}
                {make_bar_with_text("3. Mind", scores["Mind"], data_a["Mind"], data_b["Mind"], definitions["Mind"])}
            </div>
        </div>
    </div>"""

    rerun_loading_area.clear_output()
    with rerun_result_area:
        display(HTML(html_msg))

    accept_btn = widgets.Button(description='👍 Yes (Adopt and Save)', button_style='success', layout=widgets.Layout(width='48%', height='45px'))
    reject_btn = widgets.Button(description='👎 No (Discard)', button_style='danger', layout=widgets.Layout(width='48%', height='45px'))
    decision_box = widgets.HBox([accept_btn, reject_btn], layout=widgets.Layout(justify_content='space-between', margin='15px 0 0 0'))
    decision_status = widgets.HTML(value="")

    def on_accept(b):
        # 🌟 Save process
        label = f"Using previously appended prompt: '{user_feedback_text}'"
        saved_prompts[label] = appended_prompt_template
        update_prompt_ui()
        prompt_selector.value = label
        decision_status.value = "<div style='margin-top:10px; padding:10px; background:#d4edda; color:#155724; border-radius:5px;'><b>✅ Additional instruction adopted and saved.</b> You can select or delete it anytime from the list above.</div>"

    def on_reject(b):
        decision_status.value = "<div style='margin-top:10px; padding:10px; background:#f8d7da; color:#721c24; border-radius:5px;'><b>❌ Discarded.</b> This additional instruction will not be saved.</div>"

    accept_btn.on_click(on_accept)
    reject_btn.on_click(on_reject)

    decision_container.children = [
        widgets.HTML("<h4 style='margin-top:20px; color:#333;'>Do you want to save this additional instruction and add it to the choices for next time?</h4>"),
        decision_box,
        decision_status
    ]

run_btn.on_click(on_run_click)
rerun_btn.on_click(on_rerun_click)

# Global UI display
display(widgets.HTML("<div style='background:#f4f4f4; padding:15px; border-radius:8px;'><h2>🧪 Corporate Philosophy Comparative Analysis System</h2></div>"))
display(mode_selector, ui_container, prompt_box, run_btn, initial_result_area, feedback_container, rerun_loading_area, rerun_result_area, decision_container)

HTML(value="<div style='background:#f4f4f4; padding:15px; border-radius:8px;'><h2>🧪 Corporate Philosophy Compa…

RadioButtons(layout=Layout(margin='0 0 20px 0', width='100%'), options=('1️⃣ [Classic Method] Upload HTML file…

Button(button_style='primary', description='🚀 Run Comparative Analysis', layout=Layout(height='45px', margin='…

Output()

VBox()

Output()

Output()

VBox()